In [0]:
from pyspark.sql import functions as f
from pyspark.sql.window import Window as window

def parametro(nome, padrao):
    try:
        return dbutils.widgets.get(nome)
    except Exception:
        dbutils.widgets.text(nome, padrao)
        return dbutils.widgets.get(nome)

catalogo = parametro("catalogo", "workspace")
spark.sql(f"use catalog `{catalogo.replace('`', '``')}`")

spark.sql("create schema if not exists gold")


DataFrame[]

In [0]:
df_dim_movies = (
    spark.table("silver.tb_info_filmes")
    .select(
        "id_filme", "titulo", "data_lancamento", "ano_lancamento",
        "duracao_minutos", "idioma_original", "status_filme", "sinopse"
    )
    .dropDuplicates(["id_filme"])
)

w = window.orderBy("id_filme")

df_dim_movies = (
    df_dim_movies
    .withColumn("sk_movie_id", f.row_number().over(w).cast("bigint"))
    .select(
        "sk_movie_id",
        "id_filme",
        "titulo",
        "data_lancamento",
        f.col("ano_lancamento").cast("int"),
        f.col("duracao_minutos").cast("int"),
        "idioma_original",
        "status_filme",
        "sinopse"
    )
)

(
    df_dim_movies.write
    .format("delta")
    .mode("overwrite")
    .option("overwriteSchema", "true")
    .saveAsTable("gold.dim_movies")
)

display(df_dim_movies)


/databricks/python/lib/python3.12/site-packages/pyspark/sql/connect/expressions.py:1155: UserWarning: WARN WindowExpression: No Partition Defined for Window operation! Moving all data to a single partition, this can cause serious performance degradation.
  warnings.warn(


sk_movie_id,id_filme,titulo,data_lancamento,ano_lancamento,duracao_minutos,idioma_original,status_filme,sinopse
1,1000004,Purple Beatz,2022-07-07,2022,86,en,Lançado,"Sarah-Jane is a young aspiring jazz singer from Bournemouth who moves to London to embark on a music career. Not long in town, she falls for the handsome Airbeats, but also sinister music producer Russell-D, who represents a darker side to the music industry."
2,1000005,Aisha Brown: The First Black Woman Ever,2020-02-14,2020,42,en,Lançado,null
3,1000007,KYLE BROWNRIGG: INTRODUCING LYLE,2022-05-27,2022,36,en,Lançado,"Kyle Brownrigg takes the stage in this hilarious half-hour stand-up special where he laments gender reveal parties, talks about his Irish boyfriend, and introduces the world to his drunk persona, Lyle."
4,1000011,Worth Your Weight in Gold,2022-07-14,2022,26,pt,Lançado,"Oscar, a renowned hypnotherapist, uses the last moments in his hotel room to say goodbye to the vertiginous Mercedes and rid old Norberto of his bitterness."
5,1000014,On va manquer !,2018-05-15,2018,null,fr,Lançado,null
6,1000030,58 Hours: The Baby Jessica Story,2021-07-31,2021,null,es,Lançado,null
7,1000054,One Hundred Years and Hope,2022-06-18,2022,107,ja,Lançado,"In a country ruled by the Liberal Democratic Party, running on austerity and neoliberal ambitions, for most of its postwar years, gender and economic inequalities have become increasingly acute in Japan. Takashi Nishihara, a filmmaker who has been following the youth protests in Japan notices that there is one party that seems to be raising issues of gender and economic in the political sphere, the Japanese Communist Party (JCP), a party about to enter its hundredth year and consistently burdened by its historical connotations. Though an outsider of the party, Nishihara gained unprecedented access to the JCP and driven by his interest in the younger party members who find hope in the JCP, the resulting documentary goes beyond party politics and observes the current grassroots leftist movements in Japan. It also becomes witness to the larger and deep-seated patriarchal system that continues to quell momentums of hope."
8,1000058,Homecoming,2023-07-12,2023,110,fr,Lançado,"Kheìdidja, in her forties, works for a wealthy Parisian family who offers her the opportunity to take care of their children for a summer in Corsica. It's an opportunity for her to return with her daughters, Jessica and Farah, to the island they left fifteen years earlier in tragic circumstances."
9,1000059,素敵な選TAXI SPECIAL〜湯けむり連続選択肢〜,2016-04-05,2016,116,ja,Lançado,"Edawakare, the driver of the Time Taxi that allows passengers to return to their life's turning points, visits a hot spring this time around. An array of guests at the inn are fraught with troubles in their life and become passengers of the Time Taxi. And somehow all the clients are actually part of a bigger picture?!"
10,1000073,A Chance To Win,2023-05-03,2023,97,fr,Lançado,"Two villages in the south of France have always been bitter rivals, but when a group of asylum seekers arrive in the community, the life of both villages is shaken up and age-old disagreements escalate. Their antagonism reaches its peak with the annual rugby derby played between the two village teams, but this time, with the new outsiders joining as unexpected recruits, the result of the 100th match will be more unpredictable than ever."


In [0]:
df_dim_genres = (
    spark.table("silver.tb_generos")
    .select("nome_genero")
    .dropDuplicates()
)

w = window.orderBy("nome_genero")

df_dim_genres = (
    df_dim_genres
    .withColumn("sk_genre_id", f.row_number().over(w).cast("bigint"))
    .select("sk_genre_id", "nome_genero")
)

df_dim_people = (
    spark.table("silver.tb_pessoas_empresas")
    .filter(f.col("tipo_entidade").isin("Ator", "Diretor", "Roteirista"))
    .select(
        f.col("nome_entidade").alias("nome_pessoa"),
        f.col("tipo_entidade").alias("tipo_pessoa")
    )
    .dropDuplicates()
)

w = window.orderBy("nome_pessoa", "tipo_pessoa")

df_dim_people = (
    df_dim_people
    .withColumn("sk_person_id", f.row_number().over(w).cast("bigint"))
    .select("sk_person_id", "nome_pessoa", "tipo_pessoa")
)

df_dim_companies = (
    spark.table("silver.tb_pessoas_empresas")
    .filter(f.col("tipo_entidade") == "Produtora")
    .select(f.col("nome_entidade").alias("nome_produtora"))
    .dropDuplicates()
)

w = window.orderBy("nome_produtora")

df_dim_companies = (
    df_dim_companies
    .withColumn("sk_company_id", f.row_number().over(w).cast("bigint"))
    .select("sk_company_id", "nome_produtora")
)

for df, tabela in [
    (df_dim_genres, "gold.dim_genres"),
    (df_dim_people, "gold.dim_people"),
    (df_dim_companies, "gold.dim_companies")
]:
    (
        df.write
        .format("delta")
        .mode("overwrite")
        .option("overwriteSchema", "true")
        .saveAsTable(tabela)
    )


/databricks/python/lib/python3.12/site-packages/pyspark/sql/connect/expressions.py:1155: UserWarning: WARN WindowExpression: No Partition Defined for Window operation! Moving all data to a single partition, this can cause serious performance degradation.
  warnings.warn(
/databricks/python/lib/python3.12/site-packages/pyspark/sql/connect/expressions.py:1155: UserWarning: WARN WindowExpression: No Partition Defined for Window operation! Moving all data to a single partition, this can cause serious performance degradation.
  warnings.warn(


In [0]:
df_dim_reviews = (
    spark.table("silver.tb_avaliacoes_usuarios")
    .groupBy("id_filme")
    .agg(
        f.count("*").cast("int").alias("qtd_avaliacoes_usuarios"),
        f.round(f.avg("nota_usuario"), 2).cast("double").alias("nota_media_usuarios")
    )
    .join(
        spark.table("gold.dim_movies").select("id_filme", "sk_movie_id"),
        "id_filme",
        "inner"
    )
    .select("sk_movie_id", "qtd_avaliacoes_usuarios", "nota_media_usuarios")
)

w = window.orderBy("sk_movie_id")

df_dim_reviews = (
    df_dim_reviews
    .withColumn("sk_review_id", f.row_number().over(w).cast("bigint"))
    .select("sk_review_id", "sk_movie_id", "qtd_avaliacoes_usuarios", "nota_media_usuarios")
)

(
    df_dim_reviews.write
    .format("delta")
    .mode("overwrite")
    .option("overwriteSchema", "true")
    .saveAsTable("gold.dim_reviews")
)

display(df_dim_reviews)


/databricks/python/lib/python3.12/site-packages/pyspark/sql/connect/expressions.py:1155: UserWarning: WARN WindowExpression: No Partition Defined for Window operation! Moving all data to a single partition, this can cause serious performance degradation.
  warnings.warn(


sk_review_id,sk_movie_id,qtd_avaliacoes_usuarios,nota_media_usuarios
1,1,1,0.1
2,5,1,3.3
3,8,1,6.8
4,17,1,5.4
5,19,1,5.3
6,20,1,4.4
7,23,3,4.75
8,24,1,4.8
9,26,1,6.6
10,33,1,7.5


In [0]:
df_bridge_movie_genre = (
    spark.table("silver.tb_generos").alias("s")
    .join(
        spark.table("gold.dim_movies").select("id_filme", "sk_movie_id").alias("m"),
        "id_filme",
        "inner"
    )
    .join(
        spark.table("gold.dim_genres").alias("g"),
        f.col("s.nome_genero") == f.col("g.nome_genero"),
        "inner"
    )
    .select("sk_movie_id", "sk_genre_id")
    .dropDuplicates()
)

df_bridge_movie_person = (
    spark.table("silver.tb_pessoas_empresas").alias("s")
    .filter(f.col("tipo_entidade").isin("Ator", "Diretor", "Roteirista"))
    .join(
        spark.table("gold.dim_movies").select("id_filme", "sk_movie_id"),
        "id_filme",
        "inner"
    )
    .join(
        spark.table("gold.dim_people").alias("p"),
        (f.col("s.nome_entidade") == f.col("p.nome_pessoa"))
        & (f.col("s.tipo_entidade") == f.col("p.tipo_pessoa")),
        "inner"
    )
    .select("sk_movie_id", "sk_person_id")
    .dropDuplicates()
)

df_bridge_movie_company = (
    spark.table("silver.tb_pessoas_empresas").alias("s")
    .filter(f.col("tipo_entidade") == "Produtora")
    .join(
        spark.table("gold.dim_movies").select("id_filme", "sk_movie_id"),
        "id_filme",
        "inner"
    )
    .join(
        spark.table("gold.dim_companies").alias("c"),
        f.col("s.nome_entidade") == f.col("c.nome_produtora"),
        "inner"
    )
    .select("sk_movie_id", "sk_company_id")
    .dropDuplicates()
)

for df, tabela in [
    (df_bridge_movie_genre, "gold.bridge_movie_genre"),
    (df_bridge_movie_person, "gold.bridge_movie_person"),
    (df_bridge_movie_company, "gold.bridge_movie_company")
]:
    (
        df.write
        .format("delta")
        .mode("overwrite")
        .option("overwriteSchema", "true")
        .saveAsTable(tabela)
    )


In [0]:
for tabela in ["silver.tb_info_filmes", "silver.tb_financeiro_filmes", "silver.tb_metricas_engajamento"]:
    if spark.table(tabela).groupBy("id_filme").count().filter("count > 1").limit(1).count():
        raise ValueError(f"Grão duplicado na origem: {tabela}")
df_fact = (
    spark.table("gold.dim_movies")
    .filter(f.col("status_filme") == "Lançado")
    .select("sk_movie_id", "id_filme")
    .join(spark.table("silver.tb_financeiro_filmes"), "id_filme", "left")
    .join(spark.table("silver.tb_metricas_engajamento"), "id_filme", "left")
    .select(
        f.col("sk_movie_id").cast("bigint"),
        f.col("orcamento_usd").cast("decimal(18,2)"),
        f.col("receita_usd").cast("decimal(18,2)"),
        f.col("lucro_usd").cast("decimal(18,2)"),
        f.col("orcamento_brl").cast("decimal(18,2)"),
        f.col("receita_brl").cast("decimal(18,2)"),
        f.col("lucro_brl").cast("decimal(18,2)"),
        f.col("popularidade").cast("double"),
        f.col("nota_media_tmdb").cast("double"),
        f.col("qtd_votos_tmdb").cast("int"),
        f.col("nota_media_imdb").cast("double"),
        f.col("qtd_votos_imdb").cast("int")
    )
)

(
    df_fact.write
    .format("delta")
    .mode("overwrite")
    .option("overwriteSchema", "true")
    .saveAsTable("gold.fact_movies_performance")
)

display(df_fact)


sk_movie_id,orcamento_usd,receita_usd,lucro_usd,orcamento_brl,receita_brl,lucro_brl,popularidade,nota_media_tmdb,qtd_votos_tmdb,nota_media_imdb,qtd_votos_imdb
1,null,null,null,null,null,null,null,null,null,null,null
2,null,null,null,null,null,null,null,null,null,null,null
3,null,null,null,null,null,null,null,null,null,null,null
4,null,null,null,null,null,null,null,null,null,null,null
5,null,null,null,null,null,null,null,null,null,null,null
6,null,null,null,null,null,null,null,null,null,null,null
7,null,null,null,null,null,null,null,null,null,null,null
8,4700000.00,null,null,23742050.00,null,null,1.489,6.75,6,6.2,382
9,null,null,null,null,null,null,0.6,0.0,0,7.7,25
10,6000000.00,null,null,30309000.00,null,null,13.212,6.8,15,null,236


In [0]:
for tabela, chave in [
    ("dim_movies", "sk_movie_id"), ("dim_genres", "sk_genre_id"),
    ("dim_people", "sk_person_id"), ("dim_companies", "sk_company_id"),
    ("dim_reviews", "sk_review_id"), ("fact_movies_performance", "sk_movie_id")
]:
    df = spark.table("gold." + tabela)
    if df.filter(f.col(chave).isNull()).limit(1).count():
        raise ValueError(f"Chave nula em {tabela}")
    if df.groupBy(chave).count().filter("count > 1").limit(1).count():
        raise ValueError(f"Chave duplicada em {tabela}")

for ponte, dimensao, chave in [
    ("bridge_movie_genre", "dim_genres", "sk_genre_id"),
    ("bridge_movie_person", "dim_people", "sk_person_id"),
    ("bridge_movie_company", "dim_companies", "sk_company_id")
]:
    df = spark.table("gold." + ponte)
    if df.groupBy("sk_movie_id", chave).count().filter("count > 1").limit(1).count():
        raise ValueError(f"Par duplicado em {ponte}")
    for dim, fk in [(dimensao, chave), ("dim_movies", "sk_movie_id")]:
        if df.join(spark.table("gold." + dim).select(fk), fk, "left_anti").limit(1).count():
            raise ValueError(f"Referência órfã em {ponte}: {fk}")

filmes = spark.table("gold.dim_movies")
fato = spark.table("gold.fact_movies_performance")
for tabela in ["fact_movies_performance", "dim_reviews"]:
    if spark.table("gold." + tabela).join(filmes.select("sk_movie_id"), "sk_movie_id", "left_anti").limit(1).count():
        raise ValueError(f"Filme órfão em {tabela}")
if spark.table("gold.dim_reviews").groupBy("sk_movie_id").count().filter("count > 1").limit(1).count():
    raise ValueError("Mais de um agregado de avaliações por filme")
if fato.count() != filmes.filter(f.col("status_filme") == "Lançado").count():
    raise ValueError("Fato não corresponde ao conjunto de filmes lançados")
print("Unicidade, grão e integridade referencial verificados")


Unicidade, grão e integridade referencial verificados


In [0]:
q1 = (
    spark.table("gold.fact_movies_performance")
    .agg(f.round(f.sum("receita_brl"), 2).alias("receita_total_brl"))
)

q2 = (
    spark.table("gold.fact_movies_performance")
    .join(spark.table("gold.dim_movies"), "sk_movie_id")
    .filter(f.col("popularidade").isNotNull())
    .select("titulo", "popularidade")
    .orderBy(f.col("popularidade").desc())
    .limit(5)
)

q3 = (
    spark.table("gold.bridge_movie_genre")
    .join(spark.table("gold.dim_genres"), "sk_genre_id")
    .groupBy("nome_genero")
    .agg(f.countDistinct("sk_movie_id").alias("qtd_filmes"))
    .orderBy(f.col("qtd_filmes").desc(), f.col("nome_genero"))
)

display(q1)
display(q2)
display(q3)


receita_total_brl
816738964860.76


titulo,popularidade
blue beetle,2994.357
Gran Turismo,2680.593
La Fellinette,2020.0
The Fear Footage 2: Curse of the Tape,2019.0
Battipaglia 1969,1969.0


nome_genero,qtd_filmes
Drama,30353
Documentary,18560
Comedy,17312
Thriller,9406
Horror,9128
Romance,6992
Action,5547
Crime,4312
Animation,4154
Tv Movie,3674


In [0]:
w_rank = window.orderBy(f.col("receita_usd").desc())

q4 = (
    spark.table("gold.fact_movies_performance")
    .join(spark.table("gold.dim_movies"), "sk_movie_id")
    .filter(f.col("receita_usd").isNotNull())
    .select("titulo", "receita_usd", "receita_brl")
    .withColumn("posicao_ranking", f.rank().over(w_rank))
    .orderBy("posicao_ranking", "titulo")
    .limit(10)
)

display(q4)


/databricks/python/lib/python3.12/site-packages/pyspark/sql/connect/expressions.py:1155: UserWarning: WARN WindowExpression: No Partition Defined for Window operation! Moving all data to a single partition, this can cause serious performance degradation.
  warnings.warn(


titulo,receita_usd,receita_brl,posicao_ranking
Avengers: Endgame,2800000000.00,14144200000.00,1
Avatar: The Way of Water,2320250281.00,11720744294.47,2
AVENGERS: INFINITY WAR,2052415039.00,10367774569.51,3
spider-man: no way home,1921847111.00,9708210681.22,4
The Lion King,1663075401.00,8401025388.15,5
Top Gun: Maverick,1488732821.00,7520333845.28,6
Barbie,1428545028.00,7216295208.94,7
The Super Mario Bros. Movie,1355725263.00,6848446166.04,8
Black Panther,1349926083.00,6819151608.27,9
Star Wars: The Last Jedi,1332698830.00,6732128139.75,10


In [0]:
data_maxima = (
    spark.table("gold.dim_movies")
    .filter(f.col("status_filme") == "Lançado")
    .filter(f.col("data_lancamento").isNotNull())
    .filter(f.col("data_lancamento") <= f.current_date())
    .agg(f.max("data_lancamento").alias("data_max"))
    .first()["data_max"]
)

if data_maxima is None:
    raise ValueError("Não há data de lançamento realizada válida na base")

data_inicio_2 = (
    spark.range(1)
    .select(f.add_months(f.lit(data_maxima), -24).alias("data_inicio"))
    .first()["data_inicio"]
)

q5 = (
    spark.table("gold.bridge_movie_person")
    .join(
        spark.table("gold.dim_people").filter(f.col("tipo_pessoa") == "Ator"),
        "sk_person_id"
    )
    .join(spark.table("gold.dim_movies"), "sk_movie_id")
    .filter(f.col("status_filme") == "Lançado")
    .filter(f.col("data_lancamento").between(f.lit(data_inicio_2), f.lit(data_maxima)))
    .groupBy("nome_pessoa")
    .agg(f.countDistinct("sk_movie_id").alias("qtd_participacoes"))
    .orderBy(f.col("qtd_participacoes").desc(), f.col("nome_pessoa"))
    .limit(1)
)

display(q5)


nome_pessoa,qtd_participacoes
Kevin Hart,64


In [0]:
data_inicio_5 = (
    spark.range(1)
    .select(f.add_months(f.lit(data_maxima), -60).alias("data_inicio"))
    .first()["data_inicio"]
)

q6 = (
    spark.table("gold.bridge_movie_company")
    .join(spark.table("gold.dim_companies"), "sk_company_id")
    .join(spark.table("gold.dim_movies"), "sk_movie_id")
    .join(spark.table("gold.fact_movies_performance"), "sk_movie_id")
    .filter(f.col("status_filme") == "Lançado")
    .filter(f.col("data_lancamento").between(f.lit(data_inicio_5), f.lit(data_maxima)))
    .filter(f.col("lucro_brl").isNotNull())
    .groupBy("nome_produtora")
    .agg(f.round(f.sum("lucro_brl"), 2).alias("lucro_total_brl"))
    .orderBy(f.col("lucro_total_brl").desc(), f.col("nome_produtora"))
    .limit(1)
)

display(q6)


nome_produtora,lucro_total_brl
Universal Pictures,29158923373.49
